# Lyrics Mood Modelling (Mood Classification) Notebook

This notebook contains the code used to implement the 3.4.2 Application of BERT Models for Section-Wise Mood Classification.

Three pretrained BERT models - Roberta, Distilroberta and Distroberta Variant by Michellejieli were imported from transformers library and applied to each section of the lyrics splitted in the Data Pre-proceesing notebook.

The data from the Data preprocessing notebook was imported to google colab. I did this mood classification in google colab because Transformer Hugging Face models were not compactible to my local PC and gave me lots of errors.

In [ ]:
# Import Libraries
import numpy as np
import pandas as pd
from transformers import AutoTokenizer, AutoModelForSequenceClassification
import torch
from scipy.special import softmax

In [ ]:
# Download files containing the dataset with the splitted lyrics for each location.
from google.colab import files
files.upload()

Saving mall_rankMerged_split.csv to mall_rankMerged_split.csv
Saving gym_rankMerged_split.csv to gym_rankMerged_split.csv
Saving restaurant_rankMerged_split.csv to restaurant_rankMerged_split.csv
Saving bar_rankMerged_split.csv to bar_rankMerged_split.csv
Saving office_rankMerged_split.csv to office_rankMerged_split.csv
Saving library_rankMerged_split.csv to library_rankMerged_split.csv
Saving trainbus_rankMerged_split.csv to trainbus_rankMerged_split.csv
Saving bedroom_rankMerged_split.csv to bedroom_rankMerged_split.csv


{'mall_rankMerged_split.csv': b'21_25_Female_AR,21_25_Male_AR,26_30_Female_AR,26_30_Male_AR,S/N,Section_1,Section_2,Section_3,Section_4,Section_5,Section_6,acousticness,artist_id,artist_name,cleaned_lyrics,cleaned_lyrics_sections,danceability,duration_ms,energy,genre,key,liveness,loudness,lyrics,mode,popularity,release_date,speechiness,tempo,track_id,track_name,track_name_count,valence\n5.0,3.4,5.0,5.0,1,"[Chorus] Now he\'s thinkin\' \'bout me every night, oh Is it that sweet? I guess so Say you can\'t sleep, baby, I know That\'s that me espresso Move it up, down, left, right, oh Switch it up like Nintendo Say you can\'t sleep, baby, I know That\'s that me espresso [Verse 1] I can\'t relate to desperation My give-a-fucks are on vacation And I got this one boy and he won\'t stop calling When they act this way, I know I got \'em [Pre-Chorus] (Mm) Too bad your ex don\'t do it for ya (Mm) Walked in and dream-came-trued it","for ya (Mm) Soft skin and I perfumed it for ya (Yes) I know I Moun

In [ ]:
# Read the dataset using pandas
bar = pd.read_csv('/content/bar_rankMerged_split.csv')
bedroom = pd.read_csv('/content/bedroom_rankMerged_split.csv')
gym = pd.read_csv('/content/gym_rankMerged_split.csv')
library = pd.read_csv('/content/library_rankMerged_split.csv')
mall = pd.read_csv('/content/mall_rankMerged_split.csv')
office = pd.read_csv('/content/office_rankMerged_split.csv')
restaurant = pd.read_csv('/content/restaurant_rankMerged_split.csv')
trainbus = pd.read_csv('/content/trainbus_rankMerged_split.csv')

Mood Classification: Roberta

In [ ]:
from transformers import pipeline

classifier_roberta = pipeline(task="text-classification", model="SamLowe/roberta-base-go_emotions", top_k=None) # make top_k = None to get all the confidence score of the emotions predicted

sentences = bar['Section_1'].loc[2]

model_outputs = classifier_roberta(sentences)
print(model_outputs[0])
# produces a list of dicts for each of the labels

/usr/local/lib/python3.10/dist-packages/huggingface_hub/utils/_token.py:89: UserWarning: 
The secret `HF_TOKEN` does not exist in your Colab secrets.
To authenticate with the Hugging Face Hub, create a token in your settings tab (https://huggingface.co/settings/tokens), set it as secret in your Google Colab and restart your session.
You will be able to reuse this secret in all of your notebooks.
Please note that authentication is recommended but still optional to access public models or datasets.
  warnings.warn(


config.json:   0%|          | 0.00/1.92k [00:00<?, ?B/s]

model.safetensors:   0%|          | 0.00/499M [00:00<?, ?B/s]

tokenizer_config.json:   0%|          | 0.00/380 [00:00<?, ?B/s]

vocab.json:   0%|          | 0.00/798k [00:00<?, ?B/s]

merges.txt:   0%|          | 0.00/456k [00:00<?, ?B/s]

tokenizer.json:   0%|          | 0.00/2.11M [00:00<?, ?B/s]

special_tokens_map.json:   0%|          | 0.00/280 [00:00<?, ?B/s]

[{'label': 'neutral', 'score': 0.34515491127967834}, {'label': 'disapproval', 'score': 0.31971827149391174}, {'label': 'annoyance', 'score': 0.16120921075344086}, {'label': 'curiosity', 'score': 0.11126560717821121}, {'label': 'anger', 'score': 0.09322257339954376}, {'label': 'confusion', 'score': 0.051902998238801956}, {'label': 'caring', 'score': 0.043625250458717346}, {'label': 'disappointment', 'score': 0.028020845726132393}, {'label': 'approval', 'score': 0.016005832701921463}, {'label': 'sadness', 'score': 0.013256785459816456}, {'label': 'realization', 'score': 0.007354218512773514}, {'label': 'optimism', 'score': 0.007124615833163261}, {'label': 'desire', 'score': 0.005355802830308676}, {'label': 'disgust', 'score': 0.00457649165764451}, {'label': 'love', 'score': 0.004296520259231329}, {'label': 'remorse', 'score': 0.004097439348697662}, {'label': 'fear', 'score': 0.0031252929475158453}, {'label': 'embarrassment', 'score': 0.00258392421528697}, {'label': 'nervousness', 'score'

In [ ]:
def classify_sections(row, max_sections):
    """
    Classify moods uisng Roberta model and get the label with the highest score for each section.

    Args:
        row (pd.Series): A row from a DataFrame containing text in different sections (like 'Section_1', 'Section_2', etc.).
        max_sections (int): The maximum number of sections to consider in the row.

    Returns:
        list: A list of the highest-scoring labels (e.g., moods) for each section, or None for any sections that are missing or don't have valid content.
    """

    section_labels = []  # This will store the best labels for each section

    # Loop through each section, starting from Section_1 up to Section_max_sections
    for i in range(1, max_sections + 1):
        section_column = f'Section_{i}'  # Create the section column name dynamically, like 'Section_1', 'Section_2', etc.

        # Make sure the section actually exists in the row and it’s not empty (not NaN)
        if section_column in row.index and pd.notna(row[section_column]):
            section_text = row[section_column]  # Grab the text from the current section
            model_outputs = classifier_roberta(section_text)  # Pass the section text through the classifier

            # The model's output is a nested list.
            if isinstance(model_outputs, list) and len(model_outputs) > 0 and isinstance(model_outputs[0], list):
                inner_outputs = model_outputs[0]

                # Now let’s find the label with the highest score using max(), pretty straightforward
                top_label = max(inner_outputs, key=lambda x: x['score'])['label']
            else:
                top_label = None

            section_labels.append(top_label)  # Add the top label for this section to our results list
        else:
            section_labels.append(None)  # If the section doesn't exist or is NaN, append None

    # Return the list of labels—one for each section
    return section_labels


# Function to apply mood detection to the entire DataFrame
def apply_mood_detection(df):
    """
    Apply the mood detection function to each row of the DataFrame.

    Args:
        df (pd.DataFrame): The DataFrame containing various sections, each with text to be classified.

    Returns:
        pd.DataFrame: The original DataFrame with an added 'section_moods' column, containing a list of detected moods for each row.
    """

    # Figure out how many sections there are by counting the columns that start with 'Section_'
    section_columns = [col for col in df.columns if col.startswith('Section_')]
    max_sections = len(section_columns)  # This tells us the highest numbered section to consider

    # Apply the classify_sections function to each row of the DataFrame to get the mood
    df['section_moods'] = df.apply(classify_sections, axis=1, max_sections=max_sections)

    # Return the updated DataFrame with the new column of moods
    return df

# Apply Roberta to bedroom data using apply_mood_detection
bedroom = apply_mood_detection(bedroom)
print(bedroom[['Section_1', 'section_moods']].head())

                                           Section_1  \
0  [Verse 1] Lady, pick it up it’s me calling Let...   
1  Do you believe in love at first sight? The fir...   
2                                   Lyrics not found   
3  [Chorus] Waiting for tonight, oh When you woul...   
4  [Intro] Ooh, sometimes Mind still Ooh, sometim...   

                                       section_moods  
0  [admiration, gratitude, neutral, None, None, N...  
1  [neutral, neutral, neutral, None, None, None, ...  
2  [neutral, None, None, None, None, None, None, ...  
3  [desire, neutral, desire, None, None, None, No...  
4  [neutral, neutral, neutral, None, None, None, ...  


In [ ]:
# Apply Roberta Model to the rest of the dataset
bar = apply_mood_detection(bar)
gym = apply_mood_detection(gym)
library = apply_mood_detection(library)
mall = apply_mood_detection(mall)
office = apply_mood_detection(office)
restaurant = apply_mood_detection(restaurant)
trainbus = apply_mood_detection(trainbus)

##Mood Classification: Distilroberta Mitch

In [ ]:
# call the distilroberta mitch BERT model and test it on 'I love you'
classifier_mich = pipeline("sentiment-analysis", model="michellejieli/emotion_text_classifier")
classifier_mich("I love this!")

config.json:   0%|          | 0.00/1.09k [00:00<?, ?B/s]

pytorch_model.bin:   0%|          | 0.00/329M [00:00<?, ?B/s]

tokenizer_config.json:   0%|          | 0.00/413 [00:00<?, ?B/s]

vocab.json:   0%|          | 0.00/798k [00:00<?, ?B/s]

merges.txt:   0%|          | 0.00/456k [00:00<?, ?B/s]

tokenizer.json:   0%|          | 0.00/2.11M [00:00<?, ?B/s]

special_tokens_map.json:   0%|          | 0.00/280 [00:00<?, ?B/s]

[{'label': 'joy', 'score': 0.9887555241584778}]

In [ ]:
# Initialize the sentiment analysis pipeline
classifier_mich = pipeline("sentiment-analysis", model="michellejieli/emotion_text_classifier")

# Function to classify sentiments and get the label with the highest score for each section
def classify_sections_mitch(row, max_sections):
    """
    Classify moods uisng Roberta model and get the label with the highest score for each section.

    Args:
        row (pd.Series): A row from a DataFrame containing text in different sections (like 'Section_1', 'Section_2', etc.).
        max_sections (int): The maximum number of sections to consider in the row.

    Returns:
        list: A list of the highest-scoring labels (e.g., moods) for each section, or None for any sections that are missing or don't have valid content.
    """
    section_sentiments = [] # This will store the best labels for each section
    for i in range(1, max_sections + 1):  # Loop over the available sections
        section_column = f'Section_{i}'
        if section_column in row.index and pd.notna(row[section_column]):  # Ensure the section exists and is not NaN
            section_text = row[section_column]
            model_outputs = classifier_mich(section_text)

            # Since model_outputs is a list of dicts, extract the label with the highest score
            if isinstance(model_outputs, list) and len(model_outputs) > 0 and isinstance(model_outputs[0], dict):
                top_label = model_outputs[0]['label']
            else:
                top_label = None  # Handle unexpected cases

            section_sentiments.append(top_label)
        else:
            section_sentiments.append(None)  # Handle missing or NaN sections with None

    return section_sentiments

# Apply the function to the DataFrame
def apply_mood_detection_mitch(df):
    # Determine the number of sections based on the columns
    section_columns = [col for col in df.columns if col.startswith('Section_')]
    max_sections = len(section_columns)

    # Apply the classify_sentiments function
    df['section_mood_mitch'] = df.apply(classify_sections_mitch, axis=1, max_sections=max_sections)

    return df

In [ ]:
# Apply the Distilroberta Mich model to all the dataset
bedroom = apply_mood_detection_mitch(bedroom)
bar = apply_mood_detection_mitch(bar)
gym = apply_mood_detection_mitch(gym)
library = apply_mood_detection_mitch(library)
mall = apply_mood_detection_mitch(mall)
office = apply_mood_detection_mitch(office)
restaurant = apply_mood_detection_mitch(restaurant)
trainbus = apply_mood_detection_mitch(trainbus)

##Mood Classification: Distilroberta

In [ ]:
# initalise the distilroberta model and test on 'i love this!)
classifier_jhart = pipeline("text-classification", model="j-hartmann/emotion-english-distilroberta-base", return_all_scores=True)
classifier_jhart("I love this!")

config.json:   0%|          | 0.00/1.00k [00:00<?, ?B/s]

pytorch_model.bin:   0%|          | 0.00/329M [00:00<?, ?B/s]

tokenizer_config.json:   0%|          | 0.00/294 [00:00<?, ?B/s]

vocab.json:   0%|          | 0.00/798k [00:00<?, ?B/s]

merges.txt:   0%|          | 0.00/456k [00:00<?, ?B/s]

tokenizer.json:   0%|          | 0.00/1.36M [00:00<?, ?B/s]

special_tokens_map.json:   0%|          | 0.00/239 [00:00<?, ?B/s]

/usr/local/lib/python3.10/dist-packages/transformers/pipelines/text_classification.py:104: UserWarning: `return_all_scores` is now deprecated,  if want a similar functionality use `top_k=None` instead of `return_all_scores=True` or `top_k=1` instead of `return_all_scores=False`.
  warnings.warn(


[[{'label': 'anger', 'score': 0.004419785924255848},
  {'label': 'disgust', 'score': 0.0016119909705594182},
  {'label': 'fear', 'score': 0.0004138524236623198},
  {'label': 'joy', 'score': 0.9771687984466553},
  {'label': 'neutral', 'score': 0.005764583125710487},
  {'label': 'sadness', 'score': 0.002092392183840275},
  {'label': 'surprise', 'score': 0.00852868054062128}]]

In [ ]:
# Function to classify emotions and get the label with the highest score for each section
def classify_sections_jhart(row, max_sections):
    section_emotions = []
    for i in range(1, max_sections + 1):  # Loop over the available sections dynamically
        section_column = f'Section_{i}'
        if section_column in row.index and pd.notna(row[section_column]):  # Ensure the section exists and is not NaN
            section_text = row[section_column]
            model_outputs = classifier_jhart(section_text)

            # Since model_outputs is a list containing another list of dicts, extract the label with the highest score
            if isinstance(model_outputs, list) and len(model_outputs) > 0 and isinstance(model_outputs[0], list):
                inner_outputs = model_outputs[0]  # Unwrap the first (and only) element
                top_label = max(inner_outputs, key=lambda x: x['score'])['label']
            else:
                top_label = None  # Handle unexpected cases

            section_emotions.append(top_label)
        else:
            section_emotions.append(None)  # Handle missing or NaN sections with None

    return section_emotions

# Apply the function to the DataFrame dynamically
def apply_mood_detection_jhart(df):
    # Determine the number of sections dynamically based on the columns
    section_columns = [col for col in df.columns if col.startswith('Section_')]
    max_sections = len(section_columns)

    # Apply the classify_emotions function
    df['section_mood_jhart'] = df.apply(classify_sections_hart, axis=1, max_sections=max_sections)

    return df

/usr/local/lib/python3.10/dist-packages/transformers/pipelines/text_classification.py:104: UserWarning: `return_all_scores` is now deprecated,  if want a similar functionality use `top_k=None` instead of `return_all_scores=True` or `top_k=1` instead of `return_all_scores=False`.
  warnings.warn(


In [ ]:
# Apply the distilroberta model on the splitted lyrics
bedroom = apply_mood_detection_jhart(bedroom)
bar = apply_mood_detection_jhart(bar)
gym = apply_mood_detection_jhart(gym)
library = apply_mood_detection_jhart(library)
mall = apply_mood_detection_jhart(mall)
office = apply_mood_detection_jhart(office)
restaurant = apply_mood_detection_jhart(restaurant)
trainbus = apply_mood_detection_jhart(trainbus)

In [ ]:
trainbus.head(5)

,21_25_Female_AR,21_25_Male_AR,26_30_Female_AR,26_30_Male_AR,S/N,Section_1,Section_10,Section_11,Section_12,Section_13,...,release_date,speechiness,tempo,track_id,track_name,track_name_count,valence,section_moods,section_mood_mitch,section_mood_jhart
0,4.4,2.9,2.1,1.3,1,Lyrics not found,NaN,NaN,NaN,NaN,...,03/11/2023,0.3720,92.380,6LSEswtC2XA3fNjxwXzSMJ,SYRGAS (Till Anna) - J.O.X Remix,0,0.342,"[neutral, None, None, None, None, None, None, ...","[neutral, None, None, None, None, None, None, ...","[neutral, None, None, None, None, None, None, ..."
1,4.4,2.9,2.1,1.3,2,Lyrics not found,NaN,NaN,NaN,NaN,...,22/09/2023,0.0731,139.885,22F3ejBpo8VAW1uI7mq32G,FUCKING RAGGARBIL,0,0.304,"[neutral, None, None, None, None, None, None, ...","[neutral, None, None, None, None, None, None, ...","[neutral, None, None, None, None, None, None, ..."
2,3.7,2.5,1.4,1.3,3,Lyrics not found,NaN,NaN,NaN,NaN,...,01/12/2023,0.0779,144.955,6DhMtmrn1rmxntTVQhvQrb,TA EN ÖL (DOH DAH),0,0.816,"[neutral, None, None, None, None, None, None, ...","[neutral, None, None, None, None, None, None, ...","[neutral, None, None, None, None, None, None, ..."
3,3.7,2.7,1.8,1.3,4,Lyrics not found,NaN,NaN,NaN,NaN,...,10/11/2023,0.2750,170.038,6LbRmYMXgUx5hI8bo3EIXj,Hatar mig,2,0.686,"[neutral, None, None, None, None, None, None, ...","[neutral, None, None, None, None, None, None, ...","[neutral, None, None, None, None, None, None, ..."
4,3.7,3.2,2.1,1.3,5,Lyrics not found,NaN,NaN,NaN,NaN,...,29/12/2023,0.2110,109.802,6HhMBB9ALXKnRn6ZsVdIFD,LAVISH 2.0,0,0.506,"[neutral, None, None, None, None, None, None, ...","[neutral, None, None, None, None, None, None, ...","[neutral, None, None, None, None, None, None, ..."


## Save dataframe with the moods to use it for further preprocessing the Data Preprocessing Notebook

In [ ]:
# Save each DataFrame as a CSV file with specific filenames
bedroom.to_csv('bedroom_dataset.csv', index=False)
bar.to_csv('bar_dataset.csv', index=False)
gym.to_csv('gym_dataset.csv', index=False)
library.to_csv('library_dataset.csv', index=False)
mall.to_csv('mall_dataset.csv', index=False)
office.to_csv('office_dataset.csv', index=False)
restaurant.to_csv('restaurant_dataset.csv', index=False)
trainbus.to_csv('trainbus_dataset.csv', index=False)
